# 19 · Neural networks and model selection — Supervised · Classification & Regression

**This notebook demonstrates classification.**

**Question:** When does extra network capacity learn useful structure, and when does it learn noise?

**Prerequisites:** Train/validation splits, classification accuracy, and gradients. **Time:** 45–55 minutes.

## Run and explore

Run cells from top to bottom with **Shift + Enter**, or select **Run → Run All Cells**. Each notebook is independent. Read each prediction prompt before using the controls.

All data is synthetic unless stated otherwise. Controls select prepared results, so moving them does not retrain a model. Seeds make comparisons repeatable. Hover for values and double-click a chart to reset its zoom.

## Workshop delivery plan (50–70 minutes)

**Opening question:** How can a network memorize noise while looking more successful?

By the end, learners should be able to:

- connect capacity to nonlinear boundaries
- diagnose overfitting
- use validation and regularization

Suggested flow: 5 minutes for the opening prediction, 12 minutes for the first live experiment, 15 minutes for paired core exercises, 10 minutes for the second demonstration, 10 minutes for group explanation, and 5–15 minutes for debrief or stretch work. Ask learners to state a prediction before touching a control and cite a visible value, boundary, or metric in every explanation.

In [1]:
import warnings
import numpy as np
import pandas as pd
import plotly.graph_objects as go
from plotly.subplots import make_subplots
from IPython.display import display
import plotly.io as pio
from sklearn.datasets import make_moons
from sklearn.model_selection import train_test_split
from sklearn.neural_network import MLPClassifier
from sklearn.metrics import accuracy_score
from sklearn.exceptions import ConvergenceWarning
warnings.filterwarnings('ignore',category=ConvergenceWarning)
pio.renderers.default="plotly_mimetype+notebook"; pio.templates.default="plotly_white"
BLUE,ORANGE="#2563eb","#c2410c"
X,y=make_moons(n_samples=650,noise=.25,random_state=19)
X_train,X_val,y_train_clean,y_val=train_test_split(X,y,train_size=120,stratify=y,random_state=19)
y_train=y_train_clean.copy(); flip=np.random.default_rng(19).choice(len(y_train),size=24,replace=False); y_train[flip]=1-y_train[flip]
xx,yy=np.meshgrid(np.linspace(-1.7,2.7,140),np.linspace(-1.3,1.8,120)); grid=np.c_[xx.ravel(),yy.ravel()]

## 1. Hidden units build nonlinear features

A neuron computes a weighted sum, adds a bias, then applies an activation. Hidden layers combine many such features. With no hidden layer, a linear boundary cannot solve curved geometry well.

To make overfitting visible, the small training set contains 20% deliberately flipped labels; validation labels remain clean. We vary hidden units while holding the split and other settings fixed. **Predict:** Does training accuracy always track validation accuracy?

In [2]:
units=[1,2,4,8,16,32,64]; cases=[]
for h in units:
 m=MLPClassifier(hidden_layer_sizes=(h,h),activation='tanh',solver='lbfgs',alpha=1e-8,max_iter=5000,random_state=20).fit(X_train,y_train)
 cases.append(dict(h=h,model=m,train=accuracy_score(y_train,m.predict(X_train)),val=accuracy_score(y_val,m.predict(X_val)),surface=m.predict_proba(grid)[:,1].reshape(xx.shape)))
c=cases[3]; fig=go.Figure()
fig.add_trace(go.Contour(x=xx[0],y=yy[:,0],z=c['surface'],colorscale='RdBu',zmin=0,zmax=1,contours=dict(start=.5,end=.5,size=1),showscale=False,name='p(class 1)'))
for cls,color,symbol in [(0,BLUE,'circle'),(1,ORANGE,'x')]: fig.add_scatter(x=X_val[y_val==cls,0],y=X_val[y_val==cls,1],mode='markers',name=f'Validation class {cls}',marker=dict(color=color,symbol=symbol,size=8,line=dict(color='white',width=1)))
buttons=[]
for c in cases: buttons.append(dict(label=f"{c['h']} hidden units",method='update',args=[{'z':[c['surface'],None,None]},{'title.text':f"{c['h']} units: train={c['train']:.1%}, validation={c['val']:.1%}"}]))
fig.update_layout(title=f"8 units: train={cases[3]['train']:.1%}, validation={cases[3]['val']:.1%}",xaxis_title='Feature 1',yaxis_title='Feature 2',height=520,updatemenus=[dict(buttons=buttons,x=1,xanchor='right',active=3)]); fig.show()

## 2. Validation guides model selection

Training performance is optimistic because the model directly saw that data. Choose capacity and regularization with validation data, then evaluate the chosen setup once on a separate test set in a real project. Reusing the validation set for many decisions can overfit that set too.

In [3]:
table=pd.DataFrame([{'Hidden units per layer':c['h'],'Training accuracy (noisy labels)':c['train'],'Validation accuracy (clean labels)':c['val'],'Gap':c['train']-c['val']} for c in cases]); display(table.round(3))
fig2=go.Figure([go.Scatter(x=table['Hidden units per layer'],y=table['Training accuracy (noisy labels)'],mode='lines+markers',name='Training on noisy labels',line=dict(color=BLUE)),go.Scatter(x=table['Hidden units per layer'],y=table['Validation accuracy (clean labels)'],mode='lines+markers',name='Validation on clean labels',line=dict(color=ORANGE))]); fig2.update_layout(title='Capacity and generalization',xaxis_title='Hidden units per layer',yaxis_title='Accuracy',xaxis_type='log',height=420); fig2.show()

,Hidden units per layer,Training accuracy (noisy labels),Validation accuracy (clean labels),Gap
0,1,0.742,0.764,-0.022
1,2,0.808,0.794,0.014
2,4,0.842,0.738,0.104
3,8,0.875,0.702,0.173
4,16,0.933,0.698,0.235
5,32,1.000,0.653,0.347
6,64,1.000,0.655,0.345


## 3. Regularization changes effective capacity

L2 regularization (`alpha`) discourages large weights. Early stopping, dropout, data augmentation, and smaller architectures are other controls. The best choice depends on the validation design and deployment distribution.

In [4]:
alphas=[1e-8,.0001,.01,.1,1,10]; rows=[]
for a in alphas:
 m=MLPClassifier(hidden_layer_sizes=(32,32),activation='tanh',solver='lbfgs',alpha=a,max_iter=5000,random_state=21).fit(X_train,y_train); rows.append({'alpha':a,'train on noisy labels':accuracy_score(y_train,m.predict(X_train)),'validation on clean labels':accuracy_score(y_val,m.predict(X_val))})
display(pd.DataFrame(rows).round(3))

,alpha,train on noisy labels,validation on clean labels
0,0.00,1.000,0.725
1,0.00,1.000,0.715
2,0.01,1.000,0.709
3,0.10,0.975,0.725
4,1.00,0.792,0.796
5,10.00,0.517,0.500


## Workshop exercise set (20–30 minutes)

For each exercise, record **prediction → action or calculation → evidence → explanation**. Exercises 1–4 are core; 5–6 work well for pairs or group discussion.

1. **Predict the train/validation curves before revealing the table.**
2. **Find the smallest network that begins fitting flipped labels strongly.**
3. **Compare the 2-unit and 32-unit decision boundaries.**
4. **Identify the best validation capacity and explain why it is not the highest training score.**
5. **Change alpha and locate underfitting and useful regularization.**
6. **Design a train/validation/test workflow for selecting both width and alpha.**

### Stretch challenges

1. Repeat with a second split and discuss selection stability.
2. Explain double descent as an optional research extension without claiming this example proves it.

## Instructor debrief

<details><summary>Reveal expected reasoning and misconception</summary>

Use these as discussion targets rather than scripts. Ask for evidence before revealing the explanation.

1. Training rises with capacity; clean validation peaks earlier and falls.
2. Use the table: the gap grows markedly by 4–8 units and reaches its maximum at high capacity.
3. The large network forms more irregular regions to accommodate noise.
4. Validation estimates generalization; memorizing corrupted labels harms it.
5. Very large alpha collapses performance; moderate alpha improves validation here.
6. Choose on validation or nested cross-validation, then report one untouched test result.

**Common misconception to surface:** Model capacity, optimization, data size, and regularization interact; parameter count alone does not determine overfitting.

A convincing learner explanation should name what changed, what stayed fixed, the evidence in the output, and one limit on the conclusion.

</details>

## What to notice

More parameters expand what a network can represent, but optimization and regularization determine what it actually learns. One split is noisy; use cross-validation when observations are exchangeable and data permits it. Preserve groups or time order when required.

<details><summary>Practice answers</summary>

Training accuracy often rises with capacity while validation accuracy can plateau or fall. Select with validation performance and simplicity, then reserve test data for the final estimate.
</details>